In [ ]:
!pip install torch==2.1.0+cu121 torchvision==0.16.0+cu121 torchaudio==2.1.0 \
 --extra-index-url https://download.pytorch.org/whl/cu121


Looking in indexes: https://pypi.org/simple, https://download.pytorch.org/whl/cu121


In [ ]:
!pip uninstall numpy -y
!pip install numpy==1.26.4


Found existing installation: numpy 1.26.4
Uninstalling numpy-1.26.4:
  Successfully uninstalled numpy-1.26.4
  Using cached numpy-1.26.4-cp310-cp310-manylinux_2_17_x86_64.manylinux2014_x86_64.whl.metadata (61 kB)
Using cached numpy-1.26.4-cp310-cp310-manylinux_2_17_x86_64.manylinux2014_x86_64.whl (18.2 MB)


In [ ]:
!pip install \
    torch-scatter \
    torch-sparse \
    torch-cluster \
    torch-spline-conv \
    -f https://data.pyg.org/whl/torch-2.1.0+cu121.html


Looking in links: https://data.pyg.org/whl/torch-2.1.0+cu121.html


In [ ]:
!pip install torch-geometric

In [ ]:
import torch
print(torch.__version__)
print(torch.version.cuda)

2.1.0+cu121
12.1


In [ ]:
!pip install trimesh numpy-stl scikit-learn matplotlib scikit-image


# SDF conversion

In [ ]:
!pip install mcubes

In [ ]:
import os, glob, math, numpy as np, trimesh
import torch
import torch.nn as nn
import torch.nn.functional as F
from torch.utils.data import Dataset, DataLoader
from sklearn.neighbors import KDTree
import matplotlib.pyplot as plt

# PyMCubes for marching cubes reconstruction
import mcubes

device = torch.device("cuda" if torch.cuda.is_available() else "cpu")
print("Using device:", device)

SDF_RES = 128
SDF_SAVE_DIR = "/home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128"
os.makedirs(SDF_SAVE_DIR, exist_ok=True)


Using device: cuda


## SDF generation

In [ ]:
class SurfacePointCloud:
    def __init__(self, mesh, points, normals=None):
        self.mesh = mesh
        self.points = points
        self.normals = normals
        self.kd_tree = KDTree(points)

    def get_sdf_in_batches(self, query_points, batch_size=1000000):
        n_batches = int(math.ceil(query_points.shape[0] / batch_size))
        sdf_list = []
        for pts in np.array_split(query_points, n_batches):
            sdf_list.append(self.get_sdf(pts))
        return np.concatenate(sdf_list)

    def get_sdf(self, query_points):
        distances, indices = self.kd_tree.query(query_points)
        closest_points = self.points[indices[:,0]]
        vec = query_points - closest_points
        inside = np.einsum('ij,ij->i', vec, self.normals[indices[:,0]]) < 0
        distances = distances[:,0]
        distances[inside] *= -1
        return distances

def sample_sdf_fixed(mesh, num_points=500000):
    # Sample surface points
    pts, face_idx = mesh.sample(num_points//2, return_index=True)
    normals = mesh.face_normals[face_idx]
    pts += np.random.normal(scale=0.0025, size=pts.shape)  # surface jitter

    # Sample outside points around bounding box
    bbox_min, bbox_max = mesh.bounds
    padding = 0.1 * (bbox_max - bbox_min)
    num_outside = num_points - pts.shape[0]
    outside_pts = np.random.uniform(bbox_min - padding, bbox_max + padding, size=(num_outside,3))

    all_points = np.concatenate([pts, outside_pts], axis=0)

    spc = SurfacePointCloud(mesh, pts, normals)
    sdf_values = spc.get_sdf_in_batches(all_points)
    return all_points.astype(np.float32), sdf_values.astype(np.float32)


In [ ]:
mesh_files = sorted(glob.glob("/home/exouser/02_triangular_mesh_autoencoder/Dataset/drivAERnet_dataset/*.stl"))

for mesh_file in mesh_files:
    name = os.path.basename(mesh_file).replace(".stl",".npz")
    save_path = os.path.join(SDF_SAVE_DIR, name)
    if os.path.exists(save_path):
        continue
    mesh = trimesh.load(mesh_file, process=False)
    points, sdf = sample_sdf_fixed(mesh)
    np.savez_compressed(save_path, points=points, sdf=sdf)
    print(f"Saved SDF: {save_path}")


Saved SDF: /home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128/F_D_WM_WW_0001.npz
Saved SDF: /home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128/F_D_WM_WW_0002.npz
Saved SDF: /home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128/F_D_WM_WW_0003.npz
Saved SDF: /home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128/F_D_WM_WW_0004.npz
Saved SDF: /home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128/F_D_WM_WW_0005.npz
Saved SDF: /home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128/F_D_WM_WW_0006.npz
Saved SDF: /home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128/F_D_WM_WW_0008.npz
Saved SDF: /home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128/F_D_WM_WW_0009.npz
Saved SDF: /home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128/F_D_WM_WW_0010.npz
Saved SDF: /home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128/F_D_WM_WW_0011.npz
Saved SDF: /home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128/F_D_WM_WW_0012.npz

# Implicit SDF mesh autoencoder

In [ ]:
import os, glob, math, numpy as np
import torch
import torch.nn as nn
import torch.nn.functional as F
from torch.utils.data import Dataset, DataLoader
from sklearn.model_selection import train_test_split

device = torch.device("cuda" if torch.cuda.is_available() else "cpu")
print("Using device:", device)

# Paths
SDF_DIR = "/home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128"
CHECKPOINT_DIR = "/home/exouser/02_triangular_mesh_autoencoder/Model/checkpoints_sdf_MSE"
os.makedirs(CHECKPOINT_DIR, exist_ok=True)


Using device: cuda


In [ ]:
import os, glob, math, numpy as np
import torch
import torch.nn as nn
import torch.nn.functional as F
from torch.utils.data import Dataset, DataLoader
from sklearn.model_selection import train_test_split

device = torch.device("cuda" if torch.cuda.is_available() else "cpu")
print("Using device:", device)

# Paths
SDF_DIR = "/home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128"
CHECKPOINT_DIR = "/home/exouser/02_triangular_mesh_autoencoder/Model/checkpoints_sdf_CL"
os.makedirs(CHECKPOINT_DIR, exist_ok=True)


Using device: cuda


In [ ]:
import os, glob, math, numpy as np
import torch
import torch.nn as nn
import torch.nn.functional as F
from torch.utils.data import Dataset, DataLoader
from sklearn.model_selection import train_test_split

device = torch.device("cuda" if torch.cuda.is_available() else "cpu")
print("Using device:", device)

# Paths
SDF_DIR = "/home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128"
CHECKPOINT_DIR = "/home/exouser/02_triangular_mesh_autoencoder/Model/checkpoints_sdf_multipleLoss"
os.makedirs(CHECKPOINT_DIR, exist_ok=True)


Using device: cuda


In [ ]:
class SDFDataset(Dataset):
    def __init__(self, sdf_dir):
        self.files = sorted(glob.glob(os.path.join(sdf_dir, "*.npz")))

    def __len__(self):
        return len(self.files)

    def __getitem__(self, idx):
        data = np.load(self.files[idx])
        points = data['points'].astype(np.float32)
        sdf = data['sdf'].astype(np.float32).reshape(-1,1)
        return torch.from_numpy(points), torch.from_numpy(sdf)

# Load dataset
dataset = SDFDataset(SDF_DIR)

# Train/test split
train_indices, test_indices = train_test_split(range(len(dataset)), test_size=0.1, random_state=42)
train_dataset = torch.utils.data.Subset(dataset, train_indices)
test_dataset  = torch.utils.data.Subset(dataset, test_indices)

train_loader = DataLoader(train_dataset, batch_size=1, shuffle=True)
test_loader  = DataLoader(test_dataset, batch_size=1)
print(f"Train samples: {len(train_dataset)}, Test samples: {len(test_dataset)}")


Train samples: 87, Test samples: 10


In [ ]:
class SDFEncoder(nn.Module):
    def __init__(self, latent_dim=256):
        super().__init__()
        self.fc = nn.Sequential(
            nn.Linear(3, 128),
            nn.ReLU(),
            nn.Linear(128, 256),
            nn.ReLU(),
            nn.Linear(256, latent_dim)
        )
    def forward(self, x):
        return self.fc(x)

class SDFDecoder(nn.Module):
    def __init__(self, latent_dim=256):
        super().__init__()
        self.fc = nn.Sequential(
            nn.Linear(3 + latent_dim, 256),
            nn.ReLU(),
            nn.Linear(256, 256),
            nn.ReLU(),
            nn.Linear(256, 1)  # SDF value
        )
    def forward(self, x, z):
        z_expand = z.expand(x.shape[0], -1)
        return self.fc(torch.cat([x, z_expand], dim=1))

class SDFAutoencoder(nn.Module):
    def __init__(self, latent_dim=256):
        super().__init__()
        self.encoder = SDFEncoder(latent_dim)
        self.decoder = SDFDecoder(latent_dim)
    def forward(self, points):
        z = self.encoder(points)
        sdf_pred = self.decoder(points, z)
        return sdf_pred, z


## MSE loss

In [ ]:
model = SDFAutoencoder(latent_dim=256).to(device)
optimizer = torch.optim.Adam(model.parameters(), lr=1e-4)
num_epochs = 50

history = []

for epoch in range(1, num_epochs+1):
    model.train()
    total_loss = 0
    for points, sdf in train_loader:
        # points: [batch, num_points, 3] => flatten for the network
        batch_size, num_points, _ = points.shape
        points = points.view(-1, 3).to(device)  # [batch*num_points, 3]
        sdf = sdf.view(-1, 1).to(device)        # [batch*num_points, 1]

        optimizer.zero_grad()
        sdf_pred, _ = model(points)
        loss = F.mse_loss(sdf_pred, sdf)
        loss.backward()
        optimizer.step()
        total_loss += loss.item()

    avg_loss = total_loss / len(train_loader)
    history.append(avg_loss)
    print(f"Epoch {epoch} | Train MSE Loss: {avg_loss:.6f}")

    if epoch % 10 == 0:
        torch.save(model.state_dict(),
                   os.path.join(CHECKPOINT_DIR, f"sdfAE_epoch_{epoch}.pt"))


Epoch 1 | Train MSE Loss: 0.034744
Epoch 2 | Train MSE Loss: 0.011780
Epoch 3 | Train MSE Loss: 0.007835
Epoch 4 | Train MSE Loss: 0.006418
Epoch 5 | Train MSE Loss: 0.006754
Epoch 6 | Train MSE Loss: 0.006187
Epoch 7 | Train MSE Loss: 0.005445
Epoch 8 | Train MSE Loss: 0.005673
Epoch 9 | Train MSE Loss: 0.005782
Epoch 10 | Train MSE Loss: 0.005181
Epoch 11 | Train MSE Loss: 0.005723
Epoch 12 | Train MSE Loss: 0.005099
Epoch 13 | Train MSE Loss: 0.004844
Epoch 14 | Train MSE Loss: 0.004761
Epoch 15 | Train MSE Loss: 0.004521
Epoch 16 | Train MSE Loss: 0.004448
Epoch 17 | Train MSE Loss: 0.004348
Epoch 18 | Train MSE Loss: 0.004061
Epoch 19 | Train MSE Loss: 0.003962
Epoch 20 | Train MSE Loss: 0.004278
Epoch 21 | Train MSE Loss: 0.003869
Epoch 22 | Train MSE Loss: 0.003939
Epoch 23 | Train MSE Loss: 0.004078
Epoch 24 | Train MSE Loss: 0.003865
Epoch 25 | Train MSE Loss: 0.003936
Epoch 26 | Train MSE Loss: 0.003565
Epoch 27 | Train MSE Loss: 0.003718
Epoch 28 | Train MSE Loss: 0.003672
E

In [ ]:
model.eval()

PRED_SAVE_DIR = "/home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL"
os.makedirs(PRED_SAVE_DIR, exist_ok=True)

with torch.no_grad():
    for idx, (points, sdf) in enumerate(test_loader):
        batch_size, num_points, _ = points.shape

        # Flatten points: [batch, num_points, 3] -> [batch*num_points, 3]
        points_flat = points.view(-1,3).to(device)

        # Predict SDF
        sdf_pred, _ = model(points_flat)  # [batch*num_points,1]

        # Reshape back to [batch, num_points, 1]
        sdf_pred = sdf_pred.view(batch_size, num_points, 1).cpu().numpy()
        points_np = points.numpy()  # original points

        # Save predicted SDF
        save_path = os.path.join(PRED_SAVE_DIR, f"pred_{idx:03d}.npz")
        np.savez_compressed(save_path, points=points_np, sdf_pred=sdf_pred)
        print(f"Saved predicted SDF: {save_path}")


Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs/pred_000.npz


Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs/pred_001.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs/pred_002.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs/pred_003.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs/pred_004.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs/pred_005.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs/pred_006.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs/pred_007.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs/pred_008.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs/pred_009.npz


In [ ]:
import numpy as np
import trimesh
from skimage import measure
import os

# Path to your predicted SDF file
pred_file = "/home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_002.npz"

# Load predicted points and SDF
data = np.load(pred_file)
points = data['points']         # shape: [1, num_points, 3]
sdf_pred = data['sdf_pred']     # shape: [1, num_points, 1]

points = points[0]               # remove batch dim
sdf_pred = sdf_pred[0, :, 0]     # flatten to [num_points]

# --------------------------
# 1. Create a voxel grid
# Determine the bounding box
min_bound = points.min(axis=0)
max_bound = points.max(axis=0)
bbox_size = max_bound - min_bound

# Define resolution for marching cubes (higher = more detailed)
res = 128
voxel_grid = np.zeros((res, res, res), dtype=np.float32)

# Map points to voxel grid indices
normalized_pts = (points - min_bound) / bbox_size  # [0,1]
voxel_idx = (normalized_pts * (res - 1)).astype(int)
voxel_grid[voxel_idx[:,0], voxel_idx[:,1], voxel_idx[:,2]] = sdf_pred

# Optional: smooth SDF grid with simple averaging
from scipy.ndimage import gaussian_filter
voxel_grid = gaussian_filter(voxel_grid, sigma=1)

# --------------------------
# 2. Marching Cubes to extract mesh
verts, faces, normals, values = measure.marching_cubes(voxel_grid, level=0.0)

# Scale verts back to original coordinates
verts = verts / (res - 1) * bbox_size + min_bound

# --------------------------
# 3. Create Trimesh object
mesh = trimesh.Trimesh(vertices=verts, faces=faces, vertex_normals=normals)

# 4. Save the mesh
output_mesh_file = "/home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_002_mesh.obj"
mesh.export(output_mesh_file)
print(f"Mesh saved to: {output_mesh_file}")

# 5. Optional: visualize in notebook
mesh.show()


Mesh saved to: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs/pred_002_mesh.obj


## Chamfer loss

In [ ]:
import torch
import torch.nn.functional as F
import numpy as np
import os

model = SDFAutoencoder(latent_dim=256).to(device)
optimizer = torch.optim.Adam(model.parameters(), lr=1e-4)
num_epochs = 2000

history = []

num_surface_points = 5000  # Number of surface points for Chamfer per mesh

# --------------------------
# Custom Chamfer loss function
def chamfer_loss_custom(p1, p2):
    """
    p1: [batch, N, 3]
    p2: [batch, M, 3]
    returns: scalar loss
    """
    batch_size, N, _ = p1.shape
    _, M, _ = p2.shape

    # Expand for pairwise distance: [batch, N, M, 3]
    p1_expand = p1.unsqueeze(2).expand(-1, N, M, -1)
    p2_expand = p2.unsqueeze(1).expand(-1, N, M, -1)

    dist = torch.norm(p1_expand - p2_expand, dim=3)  # [batch, N, M]

    # min distance for each point
    min_p1 = torch.min(dist, dim=2)[0]  # [batch, N]
    min_p2 = torch.min(dist, dim=1)[0]  # [batch, M]

    loss = torch.mean(min_p1) + torch.mean(min_p2)
    return loss

# --------------------------
for epoch in range(1, num_epochs + 1):
    model.train()
    total_loss = 0

    for points, sdf in train_loader:
        batch_size, num_points, _ = points.shape

        # Move points and sdf to device early
        points = points.to(device)
        sdf = sdf.to(device)

        # Flatten points for network: [batch, num_points, 3] -> [batch*num_points, 3]
        points_flat = points.view(-1, 3)
        sdf_flat = sdf.view(-1, 1)

        optimizer.zero_grad()
        sdf_pred, z = model(points_flat)  # [batch*num_points, 1]

        # Base SDF MSE loss
        loss_sdf = F.mse_loss(sdf_pred, sdf_flat)

        # --------------------------
        # Custom Chamfer Loss
        # Sample small subset of surface points from ground truth
        surface_idx = torch.randperm(points.shape[1])[:num_surface_points]
        gt_surface_points = points[:, surface_idx, :]  # [batch, num_surface_points, 3]

        # Sample predicted points closest to zero SDF
        sdf_pred_flat = sdf_pred.view(batch_size, num_points)
        zero_idx = torch.topk(-torch.abs(sdf_pred_flat), num_surface_points, dim=1).indices
        pred_surface_points = torch.gather(points, 1, zero_idx.unsqueeze(-1).expand(-1, -1, 3))

        # Chamfer distance
        loss_chamfer = chamfer_loss_custom(pred_surface_points, gt_surface_points)

        # Total loss
        loss = loss_sdf + 0.5 * loss_chamfer
        loss.backward()
        optimizer.step()

        total_loss += loss.item()

    avg_loss = total_loss / len(train_loader)
    history.append(avg_loss)
    print(f"Epoch {epoch} | Total Loss: {avg_loss:.6f} | MSE: {loss_sdf.item():.6f} | Chamfer: {loss_chamfer.item():.6f}")

    # Save checkpoint every 10 epochs
    if epoch % 20 == 0:
        os.makedirs(CHECKPOINT_DIR, exist_ok=True)
        torch.save(model.state_dict(),
                   os.path.join(CHECKPOINT_DIR, f"sdfAE_chamfer_custom_epoch_{epoch}.pt"))


Epoch 1 | Total Loss: 0.594876 | MSE: 0.014918 | Chamfer: 0.442410
Epoch 2 | Total Loss: 0.190266 | MSE: 0.007469 | Chamfer: 0.304527
Epoch 3 | Total Loss: 0.164234 | MSE: 0.005933 | Chamfer: 0.283888
Epoch 4 | Total Loss: 0.154352 | MSE: 0.004909 | Chamfer: 0.302664
Epoch 5 | Total Loss: 0.151819 | MSE: 0.010027 | Chamfer: 0.333039
Epoch 6 | Total Loss: 0.149928 | MSE: 0.004849 | Chamfer: 0.269496
Epoch 7 | Total Loss: 0.149109 | MSE: 0.007694 | Chamfer: 0.308640
Epoch 8 | Total Loss: 0.148765 | MSE: 0.003752 | Chamfer: 0.258596
Epoch 9 | Total Loss: 0.147180 | MSE: 0.005749 | Chamfer: 0.263740
Epoch 10 | Total Loss: 0.147411 | MSE: 0.005372 | Chamfer: 0.275386
Epoch 11 | Total Loss: 0.145348 | MSE: 0.003888 | Chamfer: 0.266880
Epoch 12 | Total Loss: 0.144818 | MSE: 0.007507 | Chamfer: 0.321346
Epoch 13 | Total Loss: 0.144621 | MSE: 0.002303 | Chamfer: 0.268747
Epoch 14 | Total Loss: 0.143799 | MSE: 0.005537 | Chamfer: 0.265098
Epoch 15 | Total Loss: 0.144970 | MSE: 0.002355 | Chamfer

### Retraining

In [ ]:
dimport torch
import torch.nn.functional as F
import os

# --------------------------------------------------
# Paths
CHECKPOINT_PATH = "/home/exouser/02_triangular_mesh_autoencoder/Model/checkpoints_sdf_CL/sdfAE_chamfer_custom_epoch_240.pt"
CHECKPOINT_DIR  = "/home/exouser/02_triangular_mesh_autoencoder/Model/checkpoints_sdf_CL"

# --------------------------------------------------
# Model & Optimizer
model = SDFAutoencoder(latent_dim=256).to(device)
optimizer = torch.optim.Adam(model.parameters(), lr=1e-4)

# Load checkpoint
checkpoint = torch.load(CHECKPOINT_PATH, map_location=device)
model.load_state_dict(checkpoint)
#print("Loaded checkpoint from epoch 240")

# --------------------------------------------------
# Training config
start_epoch = 241
num_epochs  = 2000        # total target epoch
num_surface_points = 5000

history = []

# --------------------------------------------------
# Custom Chamfer Loss (unchanged)
def chamfer_loss_custom(p1, p2):
    """
    p1: [batch, N, 3]
    p2: [batch, M, 3]
    """
    B, N, _ = p1.shape
    _, M, _ = p2.shape

    p1_expand = p1.unsqueeze(2)          # [B, N, 1, 3]
    p2_expand = p2.unsqueeze(1)          # [B, 1, M, 3]

    dist = torch.norm(p1_expand - p2_expand, dim=3)  # [B, N, M]

    min_p1 = torch.min(dist, dim=2)[0]
    min_p2 = torch.min(dist, dim=1)[0]

    return torch.mean(min_p1) + torch.mean(min_p2)

# --------------------------------------------------
# Resume Training Loop
for epoch in range(start_epoch, num_epochs + 1):
    model.train()
    total_loss = 0.0

    for points, sdf in train_loader:
        batch_size, num_points, _ = points.shape

        points = points.to(device)
        sdf    = sdf.to(device)

        points_flat = points.view(-1, 3)
        sdf_flat    = sdf.view(-1, 1)

        optimizer.zero_grad()

        sdf_pred, z = model(points_flat)

        # ---- SDF Loss
        loss_sdf = F.mse_loss(sdf_pred, sdf_flat)

        # ---- Chamfer Loss
        surface_idx = torch.randperm(num_points, device=device)[:num_surface_points]
        gt_surface_points = points[:, surface_idx, :]

        sdf_pred_mesh = sdf_pred.view(batch_size, num_points)
        zero_idx = torch.topk(
            -torch.abs(sdf_pred_mesh),
            num_surface_points,
            dim=1
        ).indices

        pred_surface_points = torch.gather(
            points,
            1,
            zero_idx.unsqueeze(-1).expand(-1, -1, 3)
        )

        loss_chamfer = chamfer_loss_custom(pred_surface_points, gt_surface_points)

        # ---- Total Loss
        loss = loss_sdf + 0.5 * loss_chamfer
        loss.backward()
        optimizer.step()

        total_loss += loss.item()

    avg_loss = total_loss / len(train_loader)
    history.append(avg_loss)

    print(
        f"Epoch {epoch} | "
        f"Total: {avg_loss:.6f} | "
        f"MSE: {loss_sdf.item():.6f} | "
        f"Chamfer: {loss_chamfer.item():.6f}"
    )

    # ---- Save every 20 epochs
    if epoch % 20 == 0:
        os.makedirs(CHECKPOINT_DIR, exist_ok=True)
        torch.save(
            model.state_dict(),
            os.path.join(
                CHECKPOINT_DIR,
                f"sdfAE_chamfer_custom_epoch_{epoch}.pt"
            )
        )


Epoch 241 | Total: 0.137149 | MSE: 0.001838 | Chamfer: 0.258072
Epoch 242 | Total: 0.137197 | MSE: 0.001861 | Chamfer: 0.248755
Epoch 243 | Total: 0.137135 | MSE: 0.002738 | Chamfer: 0.292592
Epoch 244 | Total: 0.136513 | MSE: 0.000939 | Chamfer: 0.248191
Epoch 245 | Total: 0.135575 | MSE: 0.003629 | Chamfer: 0.249023
Epoch 246 | Total: 0.136555 | MSE: 0.004886 | Chamfer: 0.303556
Epoch 247 | Total: 0.138241 | MSE: 0.001126 | Chamfer: 0.264933
Epoch 248 | Total: 0.135094 | MSE: 0.003212 | Chamfer: 0.249450
Epoch 249 | Total: 0.136700 | MSE: 0.003182 | Chamfer: 0.247673
Epoch 250 | Total: 0.135836 | MSE: 0.002141 | Chamfer: 0.249818
Epoch 251 | Total: 0.138171 | MSE: 0.001434 | Chamfer: 0.248810
Epoch 252 | Total: 0.136061 | MSE: 0.002059 | Chamfer: 0.277734
Epoch 253 | Total: 0.136554 | MSE: 0.001518 | Chamfer: 0.258651
Epoch 254 | Total: 0.136310 | MSE: 0.001496 | Chamfer: 0.255689
Epoch 255 | Total: 0.136685 | MSE: 0.001571 | Chamfer: 0.265439
Epoch 256 | Total: 0.135857 | MSE: 0.000

In [ ]:
import os
import numpy as np
import torch

model.eval()  # set model to evaluation mode

PRED_SAVE_DIR = "/home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL"
os.makedirs(PRED_SAVE_DIR, exist_ok=True)

with torch.no_grad():
    for idx, (points, sdf) in enumerate(test_loader):
        batch_size, num_points, _ = points.shape

        # Move points to device
        points = points.to(device)

        # Flatten points: [batch, num_points, 3] -> [batch*num_points, 3]
        points_flat = points.view(-1, 3)

        # Predict SDF
        sdf_pred, _ = model(points_flat)  # [batch*num_points, 1]

        # Reshape back to [batch, num_points, 1] for saving
        sdf_pred = sdf_pred.view(batch_size, num_points, 1).cpu().numpy()
        points_np = points.cpu().numpy()  # original points

        # Save predicted SDF as compressed .npz
        save_path = os.path.join(PRED_SAVE_DIR, f"pred_{idx:03d}.npz")
        np.savez_compressed(save_path, points=points_np, sdf_pred=sdf_pred)
        print(f"Saved predicted SDF: {save_path}")


Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_000.npz


Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_001.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_002.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_003.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_004.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_005.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_006.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_007.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_008.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_009.npz


In [ ]:
import os
import numpy as np
import torch

# --------------------------------------------------
# Paths
CHECKPOINT_PATH = "/home/exouser/02_triangular_mesh_autoencoder/Model/checkpoints_sdf_CL/sdfAE_chamfer_custom_epoch_1600.pt"
PRED_SAVE_DIR   = "/home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL"

os.makedirs(PRED_SAVE_DIR, exist_ok=True)

# --------------------------------------------------
# Load trained model
model = SDFAutoencoder(latent_dim=256).to(device)
model.load_state_dict(torch.load(CHECKPOINT_PATH, map_location=device))
model.eval()

#print("Loaded model from epoch 300")

# --------------------------------------------------
# Prediction loop
with torch.no_grad():
    for idx, (points, sdf) in enumerate(test_loader):
        batch_size, num_points, _ = points.shape

        # Move points to GPU
        points = points.to(device)

        # Flatten points for implicit decoder
        points_flat = points.view(-1, 3)

        # Predict SDF
        sdf_pred, z = model(points_flat)   # [batch*num_points, 1]

        # Reshape back to per-mesh format
        sdf_pred = sdf_pred.view(batch_size, num_points, 1).cpu().numpy()
        points_np = points.cpu().numpy()

        # Save compressed prediction
        save_path = os.path.join(PRED_SAVE_DIR, f"pred_{idx:03d}.npz")
        np.savez_compressed(
            save_path,
            points=points_np,
            sdf_pred=sdf_pred
        )

        print(f"Saved predicted SDF: {save_path}")


Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_000.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_001.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_002.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_003.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_004.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_005.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_006.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_007.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_008.npz
Saved predicted SDF: /home/exouser/02_triangular_mesh_autoencode

In [ ]:
import numpy as np
import trimesh
from skimage import measure
from scipy.ndimage import gaussian_filter
import os

# Path to your predicted SDF file
pred_file = "/home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_007.npz"

# Load predicted points and SDF
data = np.load(pred_file)
points = data['points']         # shape: [1, num_points, 3]
sdf_pred = data['sdf_pred']     # shape: [1, num_points, 1]

points = points[0]              # remove batch dimension
sdf_pred = sdf_pred[0, :, 0]    # flatten SDF

# --------------------------
# 1. Create voxel grid
# Determine the bounding box
min_bound = points.min(axis=0)
max_bound = points.max(axis=0)
bbox_size = max_bound - min_bound

# Define resolution for marching cubes (higher = more detailed)
res = 128
voxel_grid = np.zeros((res, res, res), dtype=np.float32)

# Map points to voxel grid indices
normalized_pts = (points - min_bound) / bbox_size   # [0,1]
voxel_idx = (normalized_pts * (res - 1)).astype(int)

# Assign SDF values to voxel grid
voxel_grid[voxel_idx[:,0], voxel_idx[:,1], voxel_idx[:,2]] = sdf_pred

# Optional: smooth SDF grid for cleaner mesh
voxel_grid = gaussian_filter(voxel_grid, sigma=1)

# --------------------------
# 2. Marching Cubes to extract mesh
verts, faces, normals, values = measure.marching_cubes(voxel_grid, level=0.0)

# Scale vertices back to original coordinates
verts = verts / (res - 1) * bbox_size + min_bound

# --------------------------
# 3. Create Trimesh object
mesh = trimesh.Trimesh(vertices=verts, faces=faces, vertex_normals=normals)

# 4. Save the mesh
output_mesh_file = "/home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_007_mesh.obj"
mesh.export(output_mesh_file)
print(f"Mesh saved to: {output_mesh_file}")

# 5. Optional: visualize in notebook
mesh.show()


Mesh saved to: /home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_CL/pred_007_mesh.obj


## Multiple loss

In [ ]:
import torch
import torch.nn.functional as F
import numpy as np
import os
import trimesh
from sklearn.neighbors import KDTree

device = "cuda" if torch.cuda.is_available() else "cpu"

# --------------------------
# SurfacePointCloud: compute SDF
class SurfacePointCloud:
    def __init__(self, mesh, points, normals=None):
        self.mesh = mesh
        self.points = points
        self.normals = normals
        self.kd_tree = KDTree(points)

    def get_sdf(self, query_points):
        distances, indices = self.kd_tree.query(query_points)
        closest_points = self.points[indices[:,0]]
        vec = query_points - closest_points
        inside = np.einsum('ij,ij->i', vec, self.normals[indices[:,0]]) < 0
        distances = distances[:,0]
        distances[inside] *= -1
        return distances.astype(np.float32)

    def get_sdf_in_batches(self, query_points, batch_size=1000000):
        n_batches = int(np.ceil(query_points.shape[0] / batch_size))
        sdf_list = []
        for pts in np.array_split(query_points, n_batches):
            sdf_list.append(self.get_sdf(pts))
        return np.concatenate(sdf_list)

# --------------------------
# Dataset: points + sdf + normals
class SDFDataset(torch.utils.data.Dataset):
    def __init__(self, mesh_files, num_points=500000):
        self.mesh_files = mesh_files
        self.num_points = num_points

    def __len__(self):
        return len(self.mesh_files)

    def __getitem__(self, idx):
        mesh_file = self.mesh_files[idx]
        mesh = trimesh.load(mesh_file, force='mesh')

        # Sample surface points
        pts, face_idx = mesh.sample(self.num_points // 2, return_index=True)
        normals = mesh.face_normals[face_idx]  # ground-truth normals
        pts += np.random.normal(scale=0.0025, size=pts.shape)

        # Sample outside points in bounding box
        bbox_min, bbox_max = mesh.bounds
        padding = 0.1 * (bbox_max - bbox_min)
        num_outside = self.num_points - pts.shape[0]
        outside_pts = np.random.uniform(bbox_min - padding, bbox_max + padding, size=(num_outside, 3))

        all_points = np.concatenate([pts, outside_pts], axis=0)
        all_normals = np.concatenate([normals, np.zeros((num_outside, 3))], axis=0)

        # Compute SDF
        spc = SurfacePointCloud(mesh, pts, normals)
        sdf_values = spc.get_sdf_in_batches(all_points)

        return torch.from_numpy(all_points).float(), \
               torch.from_numpy(sdf_values).float().unsqueeze(-1), \
               torch.from_numpy(all_normals).float()

# --------------------------
# Train-test split
mesh_dir = "/home/exouser/02_triangular_mesh_autoencoder/Dataset/drivAERnet_dataset"
mesh_files = sorted([os.path.join(mesh_dir, f) for f in os.listdir(mesh_dir) if f.endswith('.stl')])
split = int(0.8 * len(mesh_files))
train_files, test_files = mesh_files[:split], mesh_files[split:]

train_dataset = SDFDataset(train_files)
test_dataset = SDFDataset(test_files)

train_loader = torch.utils.data.DataLoader(train_dataset, batch_size=1, shuffle=True)
test_loader  = torch.utils.data.DataLoader(test_dataset, batch_size=1, shuffle=False)

# --------------------------
# Training
model = SDFAutoencoder(latent_dim=256).to(device)
optimizer = torch.optim.Adam(model.parameters(), lr=1e-4)
num_epochs = 50
CHECKPOINT_DIR = "/home/exouser/02_triangular_mesh_autoencoder/Model/checkpoints_sdf_multipleLoss"
os.makedirs(CHECKPOINT_DIR, exist_ok=True)

num_surface_points = 5000

# Custom Chamfer loss
def chamfer_loss_custom(p1, p2):
    batch_size, N, _ = p1.shape
    _, M, _ = p2.shape
    p1_expand = p1.unsqueeze(2).expand(-1, N, M, -1)
    p2_expand = p2.unsqueeze(1).expand(-1, N, M, -1)
    dist = torch.norm(p1_expand - p2_expand, dim=3)
    min_p1 = torch.min(dist, dim=2)[0]
    min_p2 = torch.min(dist, dim=1)[0]
    return torch.mean(min_p1) + torch.mean(min_p2)

history = []

# --------------------------
for epoch in range(1, num_epochs+1):
    model.train()
    total_loss = 0

    for points, sdf, normals_gt in train_loader:
        batch_size, num_points, _ = points.shape
        points = points.to(device)
        sdf = sdf.to(device)
        normals_gt = normals_gt.to(device)

        points_flat = points.view(-1, 3)
        sdf_flat = sdf.view(-1, 1)
        points_flat.requires_grad_(True)

        optimizer.zero_grad()
        sdf_pred, z = model(points_flat)

        # --- SDF MSE ---
        loss_sdf = F.mse_loss(sdf_pred, sdf_flat)

        # --- Chamfer Loss ---
        surface_idx = torch.randperm(points.shape[1])[:num_surface_points]
        gt_surface_points = points[:, surface_idx, :]
        sdf_pred_flat = sdf_pred.view(batch_size, num_points)
        zero_idx = torch.topk(-torch.abs(sdf_pred_flat), num_surface_points, dim=1).indices
        pred_surface_points = torch.gather(points, 1, zero_idx.unsqueeze(-1).expand(-1, -1, 3))
        loss_chamfer = chamfer_loss_custom(pred_surface_points, gt_surface_points)

        # --- Eikonal Loss ---
        gradients = torch.autograd.grad(
            outputs=sdf_pred,
            inputs=points_flat,
            grad_outputs=torch.ones_like(sdf_pred),
            create_graph=True,
            retain_graph=True
        )[0]
        loss_eikonal = ((gradients.norm(dim=1) - 1) ** 2).mean()

        # --- Normal Consistency Loss ---
        pred_normals = gradients.view(batch_size, num_points, 3)
        loss_normal = 1 - F.cosine_similarity(pred_normals, normals_gt, dim=2).mean()

        # --- Total Loss ---
        loss = loss_sdf + 0.5 * loss_chamfer + 0.1 * loss_eikonal + 0.1 * loss_normal
        loss.backward()
        optimizer.step()

        total_loss += loss.item()

    avg_loss = total_loss / len(train_loader)
    history.append(avg_loss)
    print(f"Epoch {epoch} | Total Loss: {avg_loss:.6f} | SDF: {loss_sdf.item():.6f} | "
          f"Chamfer: {loss_chamfer.item():.6f} | Eikonal: {loss_eikonal.item():.6f} | Normal: {loss_normal.item():.6f}")

    if epoch % 10 == 0:
        torch.save(model.state_dict(),
                   os.path.join(CHECKPOINT_DIR, f"sdfAE_fullnorm_epoch_{epoch}.pt"))


Epoch 1 | Total Loss: 0.670136 | SDF: 0.013674 | Chamfer: 0.374719 | Eikonal: 0.266699 | Normal: 0.716193
Epoch 2 | Total Loss: 0.264370 | SDF: 0.013269 | Chamfer: 0.346328 | Eikonal: 0.114076 | Normal: 0.703658
Epoch 3 | Total Loss: 0.248645 | SDF: 0.007944 | Chamfer: 0.290413 | Eikonal: 0.136544 | Normal: 0.695105
Epoch 4 | Total Loss: 0.246252 | SDF: 0.010719 | Chamfer: 0.283423 | Eikonal: 0.136206 | Normal: 0.691988
Epoch 5 | Total Loss: 0.244363 | SDF: 0.017254 | Chamfer: 0.288411 | Eikonal: 0.136954 | Normal: 0.695343
Epoch 6 | Total Loss: 0.243719 | SDF: 0.007021 | Chamfer: 0.323998 | Eikonal: 0.116123 | Normal: 0.695546
Epoch 7 | Total Loss: 0.246810 | SDF: 0.009448 | Chamfer: 0.339522 | Eikonal: 0.117598 | Normal: 0.698856
Epoch 8 | Total Loss: 0.245228 | SDF: 0.008800 | Chamfer: 0.293098 | Eikonal: 0.141755 | Normal: 0.693563
Epoch 9 | Total Loss: 0.243108 | SDF: 0.009209 | Chamfer: 0.290523 | Eikonal: 0.103846 | Normal: 0.691069
Epoch 10 | Total Loss: 0.237109 | SDF: 0.01061

In [ ]:
import os
import torch
import numpy as np

# --------------------------
# Settings
CHECKPOINT = "/home/exouser/02_triangular_mesh_autoencoder/Model/checkpoints_sdf_multipleLoss/sdfAE_fullnorm_epoch_10.pt"
SAVE_DIR = "/home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_multipleLoss"
os.makedirs(SAVE_DIR, exist_ok=True)

model.load_state_dict(torch.load(CHECKPOINT, map_location=device))
model.eval()

# --------------------------
# Loop over test dataset
for idx, (points, sdf_gt, normals_gt) in enumerate(test_loader):
    points = points.to(device)
    batch_size, num_points, _ = points.shape

    with torch.no_grad():
        points_flat = points.view(-1, 3)
        sdf_pred, _ = model(points_flat)
        sdf_pred = sdf_pred.view(batch_size, num_points).cpu().numpy()
        points_np = points.cpu().numpy()

    # Save as .npz
    npz_file = os.path.join(SAVE_DIR, f"pred_{idx:03d}.npz")
    np.savez_compressed(npz_file, points=points_np, sdf=sdf_pred)
    print(f"Saved {npz_file}")


In [ ]:
import numpy as np
import trimesh
from skimage import measure

# --------------------------
# Path to predicted SDF .npz
npz_file = "/home/exouser/02_triangular_mesh_autoencoder/testing_noisy_outputs_multipleLoss/pred_005.npz"

# Load points and predicted SDF
data = np.load(npz_file)
points = data['points'][0]   # [num_points, 3] since batch_size=1
sdf = data['sdf'][0]         # [num_points]

# --------------------------
# 1. Normalize points into unit cube for marching cubes
min_coord = points.min(axis=0)
max_coord = points.max(axis=0)
scale = max_coord - min_coord
points_normalized = (points - min_coord) / scale.max()  # uniform scale
sdf = sdf.astype(np.float32)

# --------------------------
# 2. Create a dense 3D grid for marching cubes
grid_res = 128  # you can increase if GPU allows
grid_x, grid_y, grid_z = np.mgrid[0:1:grid_res*1j,
                                  0:1:grid_res*1j,
                                  0:1:grid_res*1j]
grid_points = np.vstack([grid_x.ravel(), grid_y.ravel(), grid_z.ravel()]).T

# --------------------------
# 3. Interpolate predicted SDF onto grid
from scipy.interpolate import griddata
sdf_grid = griddata(points_normalized, sdf, grid_points, method='linear', fill_value=1.0)
sdf_grid = sdf_grid.reshape((grid_res, grid_res, grid_res))

# --------------------------
# 4. Run Marching Cubes
vertices, faces, normals, values = measure.marching_cubes(sdf_grid, level=0.0)

# --------------------------
# 5. Transform vertices back to original coordinates
vertices = vertices / (grid_res - 1) * scale.max() + min_coord

# --------------------------
# 6. Create Trimesh and save
mesh = trimesh.Trimesh(vertices=vertices, faces=faces, vertex_normals=normals)
output_file = npz_file.replace('.npz', '_mesh.obj')
mesh.export(output_file)

print(f"Saved reconstructed mesh: {output_file}")


# Implicit SDF autoencoder with single latent code per mesh

In [ ]:
import os, glob, math, numpy as np, trimesh
import torch
import torch.nn as nn
import torch.nn.functional as F
from torch.utils.data import Dataset, DataLoader
from sklearn.model_selection import train_test_split
from sklearn.neighbors import KDTree
import matplotlib.pyplot as plt
from scipy.ndimage import gaussian_filter
from skimage import measure

device = torch.device("cuda" if torch.cuda.is_available() else "cpu")
print("Using device:", device)

SDF_RES = 128
SDF_SAVE_DIR = "/home/exouser/02_triangular_mesh_autoencoder/Dataset/sdf_128"
os.makedirs(SDF_SAVE_DIR, exist_ok=True)


Using device: cuda


In [ ]:
class SDFDataset(Dataset):
    def __init__(self, sdf_dir):
        self.files = sorted(glob.glob(os.path.join(sdf_dir, "*.npz")))

    def __len__(self):
        return len(self.files)

    def __getitem__(self, idx):
        data = np.load(self.files[idx])
        points = data['points'].astype(np.float32)
        sdf = data['sdf'].astype(np.float32).reshape(-1,1)
        return torch.from_numpy(points), torch.from_numpy(sdf)

# Load dataset
dataset = SDFDataset(SDF_SAVE_DIR)

# Train/test split
train_indices, test_indices = train_test_split(range(len(dataset)), test_size=0.1, random_state=42)
train_dataset = torch.utils.data.Subset(dataset, train_indices)
test_dataset  = torch.utils.data.Subset(dataset, test_indices)

train_loader = DataLoader(train_dataset, batch_size=1, shuffle=True)
test_loader  = DataLoader(test_dataset, batch_size=1)
print(f"Train samples: {len(train_dataset)}, Test samples: {len(test_dataset)}")


Train samples: 87, Test samples: 10


In [ ]:
# Global Encoder (PointNet-style)
class GlobalSDFEncoder(nn.Module):
    def __init__(self, latent_dim=256):
        super().__init__()
        self.mlp = nn.Sequential(
            nn.Linear(3, 128),
            nn.ReLU(),
            nn.Linear(128, 256),
            nn.ReLU(),
            nn.Linear(256, latent_dim)
        )

    def forward(self, points):
        features = self.mlp(points)          # [B, N, latent_dim]
        z = torch.max(features, dim=1)[0]    # global max pooling
        return z


In [ ]:
# Decoder
class GlobalSDFDecoder(nn.Module):
    def __init__(self, latent_dim=256):
        super().__init__()
        self.net = nn.Sequential(
            nn.Linear(3 + latent_dim, 256),
            nn.ReLU(),
            nn.Linear(256, 256),
            nn.ReLU(),
            nn.Linear(256, 1)
        )

    def forward(self, points, z):
        B, N, _ = points.shape
        z_expanded = z.unsqueeze(1).expand(B, N, -1)
        x = torch.cat([points, z_expanded], dim=-1)
        return self.net(x)


In [ ]:
# Autoencoder Wrapper
class GlobalSDFAutoencoder(nn.Module):
    def __init__(self, latent_dim=256):
        super().__init__()
        self.encoder = GlobalSDFEncoder(latent_dim)
        self.decoder = GlobalSDFDecoder(latent_dim)

    def forward(self, points):
        z = self.encoder(points)
        sdf_pred = self.decoder(points, z)
        return sdf_pred, z


In [ ]:
model = GlobalSDFAutoencoder(latent_dim=256).to(device)
optimizer = torch.optim.Adam(model.parameters(), lr=1e-4)
num_epochs = 20

for epoch in range(1, num_epochs + 1):
    model.train()
    total_loss = 0.0

    for points, sdf in train_loader:
        points = points.to(device)      # [1, N, 3]
        sdf    = sdf.to(device)         # [1, N, 1]

        optimizer.zero_grad()

        sdf_pred, z = model(points)    # sdf_pred: [1, N, 1], z: [1, 256]

        loss = F.mse_loss(sdf_pred, sdf)
        loss.backward()
        optimizer.step()

        total_loss += loss.item()

    avg_loss = total_loss / len(train_loader)
    print(f"Epoch {epoch:04d} | Loss: {avg_loss:.6f} | Latent dim: {z.shape[-1]}")


Epoch 0001 | Loss: 0.045843 | Latent dim: 256
Epoch 0002 | Loss: 0.031579 | Latent dim: 256
Epoch 0003 | Loss: 0.021736 | Latent dim: 256
Epoch 0004 | Loss: 0.014316 | Latent dim: 256
Epoch 0005 | Loss: 0.009696 | Latent dim: 256
Epoch 0006 | Loss: 0.007367 | Latent dim: 256
Epoch 0007 | Loss: 0.006522 | Latent dim: 256
Epoch 0008 | Loss: 0.005959 | Latent dim: 256
Epoch 0009 | Loss: 0.005609 | Latent dim: 256
Epoch 0010 | Loss: 0.005402 | Latent dim: 256
Epoch 0011 | Loss: 0.005264 | Latent dim: 256
Epoch 0012 | Loss: 0.005123 | Latent dim: 256
Epoch 0013 | Loss: 0.004852 | Latent dim: 256
Epoch 0014 | Loss: 0.004804 | Latent dim: 256
Epoch 0015 | Loss: 0.004682 | Latent dim: 256
Epoch 0016 | Loss: 0.004751 | Latent dim: 256
Epoch 0017 | Loss: 0.004531 | Latent dim: 256
Epoch 0018 | Loss: 0.004442 | Latent dim: 256
Epoch 0019 | Loss: 0.004352 | Latent dim: 256
Epoch 0020 | Loss: 0.004344 | Latent dim: 256


In [ ]:
def chamfer_loss_custom(p1, p2):
    """
    p1, p2: [B, N, 3] - predicted and ground truth surface points
    returns: scalar loss
    """
    B, N, _ = p1.shape
    _, M, _ = p2.shape

    # pairwise distance
    p1_expand = p1.unsqueeze(2).expand(-1, N, M, -1)
    p2_expand = p2.unsqueeze(1).expand(-1, N, M, -1)
    dist = torch.norm(p1_expand - p2_expand, dim=3)

    min_p1 = torch.min(dist, dim=2)[0]
    min_p2 = torch.min(dist, dim=1)[0]

    return torch.mean(min_p1) + torch.mean(min_p2)

# -------------------
# Training
model = GlobalSDFAutoencoder(latent_dim=256).to(device)
optimizer = torch.optim.Adam(model.parameters(), lr=1e-4)
num_epochs = 500
num_surface_points = 5000  # points sampled from SDF=0 for Chamfer

for epoch in range(1, num_epochs + 1):
    model.train()
    total_loss = 0.0

    for points, sdf in train_loader:
        points = points.to(device)  # [1, N, 3]
        sdf    = sdf.to(device)     # [1, N, 1]
        B, N, _ = points.shape

        optimizer.zero_grad()
        sdf_pred, z = model(points)  # [1, N, 1], [1, 256]

        # -----------------
        # 1. SDF MSE Loss
        loss_sdf = F.mse_loss(sdf_pred, sdf)

        # -----------------
        # 2. Chamfer Loss on zero-level set
        # Ground truth surface points
        surface_idx = torch.randperm(N)[:num_surface_points]
        gt_surface_points = points[:, surface_idx, :]  # [1, num_surface_points, 3]

        # Predicted points closest to zero SDF
        sdf_pred_flat = sdf_pred.view(B, N)
        zero_idx = torch.topk(-torch.abs(sdf_pred_flat), num_surface_points, dim=1).indices
        pred_surface_points = torch.gather(
            points, 1, zero_idx.unsqueeze(-1).expand(-1, -1, 3)
        )

        loss_chamfer = chamfer_loss_custom(pred_surface_points, gt_surface_points)

        # -----------------
        # Total loss
        loss = loss_sdf + 0.5 * loss_chamfer
        loss.backward()
        optimizer.step()

        total_loss += loss.item()

    avg_loss = total_loss / len(train_loader)
    print(f"Epoch {epoch:04d} | Total Loss: {avg_loss:.6f} | MSE: {loss_sdf.item():.6f} | Chamfer: {loss_chamfer.item():.6f}")

    # Optional: Save checkpoint every 20 epochs
    if epoch % 1 == 0:
        CHECKPOINT_DIR = "/home/exouser/02_triangular_mesh_autoencoder/Model/checkpoints_sdf_global_CL"
        os.makedirs(CHECKPOINT_DIR, exist_ok=True)
        torch.save(
            model.state_dict(),
            os.path.join(CHECKPOINT_DIR, f"sdfAE_global_chamfer_epoch_{epoch}.pt")
        )


Epoch 0001 | Total Loss: 0.780166 | MSE: 0.044343 | Chamfer: 1.195753
Epoch 0002 | Total Loss: 0.470609 | MSE: 0.030454 | Chamfer: 0.653526
Epoch 0003 | Total Loss: 0.318478 | MSE: 0.022907 | Chamfer: 0.529704
Epoch 0004 | Total Loss: 0.247033 | MSE: 0.013683 | Chamfer: 0.411657
Epoch 0005 | Total Loss: 0.201919 | MSE: 0.008680 | Chamfer: 0.345257
Epoch 0006 | Total Loss: 0.175735 | MSE: 0.008059 | Chamfer: 0.333712
Epoch 0007 | Total Loss: 0.163963 | MSE: 0.006052 | Chamfer: 0.311945
Epoch 0008 | Total Loss: 0.159112 | MSE: 0.005211 | Chamfer: 0.297242
Epoch 0009 | Total Loss: 0.155183 | MSE: 0.005144 | Chamfer: 0.294953
Epoch 0010 | Total Loss: 0.153930 | MSE: 0.004972 | Chamfer: 0.297476
Epoch 0011 | Total Loss: 0.150915 | MSE: 0.004718 | Chamfer: 0.290049
Epoch 0012 | Total Loss: 0.150618 | MSE: 0.004609 | Chamfer: 0.300382
Epoch 0013 | Total Loss: 0.149296 | MSE: 0.004956 | Chamfer: 0.298557
Epoch 0014 | Total Loss: 0.148713 | MSE: 0.003735 | Chamfer: 0.281570
Epoch 0015 | Total L

In [ ]:
import os
import torch
import torch.nn.functional as F

# -------------------
# Chamfer Loss (unchanged)
def chamfer_loss_custom(p1, p2):
    """
    p1, p2: [B, N, 3]
    """
    B, N, _ = p1.shape
    _, M, _ = p2.shape

    p1_expand = p1.unsqueeze(2).expand(-1, N, M, -1)
    p2_expand = p2.unsqueeze(1).expand(-1, N, M, -1)
    dist = torch.norm(p1_expand - p2_expand, dim=3)

    min_p1 = torch.min(dist, dim=2)[0]
    min_p2 = torch.min(dist, dim=1)[0]

    return torch.mean(min_p1) + torch.mean(min_p2)

# -------------------
# Load model and checkpoint
model = GlobalSDFAutoencoder(latent_dim=256).to(device)

checkpoint_path = (
    "/home/exouser/02_triangular_mesh_autoencoder/Model/checkpoints_sdf_global_CL/sdfAE_global_chamfer_epoch_1000.pt"
)

model.load_state_dict(torch.load(checkpoint_path, map_location=device))
print(f"Loaded checkpoint: {checkpoint_path}")

# Optimizer (reinitialized or can be loaded if saved earlier)
optimizer = torch.optim.Adam(model.parameters(), lr=1e-4)

# -------------------
# Resume Training
start_epoch = 1001
num_epochs = 500
num_surface_points = 5000

CHECKPOINT_DIR = (
    "/home/exouser/02_triangular_mesh_autoencoder/Model/checkpoints_sdf_global_CL"
)
os.makedirs(CHECKPOINT_DIR, exist_ok=True)

for epoch in range(start_epoch, start_epoch + num_epochs):
    model.train()
    total_loss = 0.0

    for points, sdf in train_loader:
        points = points.to(device)  # [1, N, 3]
        sdf    = sdf.to(device)     # [1, N, 1]
        B, N, _ = points.shape

        optimizer.zero_grad()

        sdf_pred, z = model(points)

        # -----------------
        # 1. SDF MSE Loss
        loss_sdf = F.mse_loss(sdf_pred, sdf)

        # -----------------
        # 2. Chamfer Loss (surface alignment)
        surface_idx = torch.randperm(N, device=points.device)[:num_surface_points]
        gt_surface_points = points[:, surface_idx, :]

        sdf_pred_flat = sdf_pred.view(B, N)
        zero_idx = torch.topk(
            -torch.abs(sdf_pred_flat),
            num_surface_points,
            dim=1
        ).indices

        pred_surface_points = torch.gather(
            points,
            1,
            zero_idx.unsqueeze(-1).expand(-1, -1, 3)
        )

        loss_chamfer = chamfer_loss_custom(
            pred_surface_points,
            gt_surface_points
        )

        # -----------------
        # Total Loss
        loss = loss_sdf + 0.5 * loss_chamfer
        loss.backward()
        optimizer.step()

        total_loss += loss.item()

    avg_loss = total_loss / len(train_loader)

    print(
        f"Epoch {epoch:04d} | "
        f"Total: {avg_loss:.6f} | "
        f"MSE: {loss_sdf.item():.6f} | "
        f"Chamfer: {loss_chamfer.item():.6f}"
    )

    # -----------------
    # Save checkpoint every epoch
    torch.save(
        model.state_dict(),
        os.path.join(
            CHECKPOINT_DIR,
            f"sdfAE_global_chamfer_epoch_{epoch}.pt"
        )
    )


Loaded checkpoint: /home/exouser/02_triangular_mesh_autoencoder/Model/checkpoints_sdf_global_CL/sdfAE_global_chamfer_epoch_1000.pt


Epoch 1001 | Total: 0.125117 | MSE: 0.000689 | Chamfer: 0.244090
Epoch 1002 | Total: 0.121688 | MSE: 0.001211 | Chamfer: 0.261314
Epoch 1003 | Total: 0.122607 | MSE: 0.000556 | Chamfer: 0.239793
Epoch 1004 | Total: 0.122387 | MSE: 0.001443 | Chamfer: 0.244858
Epoch 1005 | Total: 0.125204 | MSE: 0.000600 | Chamfer: 0.234098
Epoch 1006 | Total: 0.122288 | MSE: 0.004454 | Chamfer: 0.249982
Epoch 1007 | Total: 0.122882 | MSE: 0.000734 | Chamfer: 0.230757
Epoch 1008 | Total: 0.123452 | MSE: 0.001216 | Chamfer: 0.261543
Epoch 1009 | Total: 0.122268 | MSE: 0.000619 | Chamfer: 0.238794
Epoch 1010 | Total: 0.122326 | MSE: 0.005487 | Chamfer: 0.239245
Epoch 1011 | Total: 0.122376 | MSE: 0.001292 | Chamfer: 0.236889
Epoch 1012 | Total: 0.122118 | MSE: 0.000901 | Chamfer: 0.230254
Epoch 1013 | Total: 0.122594 | MSE: 0.005342 | Chamfer: 0.238193
Epoch 1014 | Total: 0.123745 | MSE: 0.001458 | Chamfer: 0.249269
Epoch 1015 | Total: 0.128969 | MSE: 0.001849 | Chamfer: 0.252521
Epoch 1016 | Total: 0.123

In [ ]:
model.eval()
PRED_SAVE_DIR = "/home/exouser/02_triangular_mesh_autoencoder/testing_latent_per_car"
os.makedirs(PRED_SAVE_DIR, exist_ok=True)

with torch.no_grad():
    for idx, (points, sdf_gt) in enumerate(test_loader):
        points = points.to(device)

        sdf_pred, z = model(points)   # [1, N, 1], [1, 256]

        # Save latent and prediction
        np.savez_compressed(
            os.path.join(PRED_SAVE_DIR, f"pred_{idx:03d}.npz"),
            points=points.cpu().numpy(),
            sdf_pred=sdf_pred.cpu().numpy(),
            latent=z.cpu().numpy()
        )
        print(f"Saved predicted SDF and latent: {idx:03d}")


Saved predicted SDF and latent: 000
Saved predicted SDF and latent: 001
Saved predicted SDF and latent: 002
Saved predicted SDF and latent: 003
Saved predicted SDF and latent: 004
Saved predicted SDF and latent: 005
Saved predicted SDF and latent: 006
Saved predicted SDF and latent: 007
Saved predicted SDF and latent: 008
Saved predicted SDF and latent: 009


In [ ]:
# Example: reconstruct first test mesh
pred_file = os.path.join(PRED_SAVE_DIR, "pred_005.npz")
data = np.load(pred_file)
points = data['points'][0]       # remove batch
sdf_pred = data['sdf_pred'][0, :, 0]

# Voxelization
min_bound = points.min(axis=0)
max_bound = points.max(axis=0)
bbox_size = max_bound - min_bound

res = 128
voxel_grid = np.zeros((res, res, res), dtype=np.float32)

normalized_pts = (points - min_bound) / bbox_size
voxel_idx = (normalized_pts * (res - 1)).astype(int)
voxel_grid[voxel_idx[:,0], voxel_idx[:,1], voxel_idx[:,2]] = sdf_pred

# Smooth
voxel_grid = gaussian_filter(voxel_grid, sigma=1)

# Marching Cubes
verts, faces, normals, values = measure.marching_cubes(voxel_grid, level=0.0)
verts = verts / (res - 1) * bbox_size + min_bound

mesh = trimesh.Trimesh(vertices=verts, faces=faces, vertex_normals=normals)
output_mesh_file = os.path.join(PRED_SAVE_DIR, "pred_005_mesh.obj")
mesh.export(output_mesh_file)
print(f"Mesh saved to: {output_mesh_file}")
mesh.show()

Mesh saved to: /home/exouser/02_triangular_mesh_autoencoder/testing_latent_per_car/pred_005_mesh.obj
